# 13 -- Animals: goose/egg lifecycle

Animals are the biggest unbuilt lever left (`PROGRESS.md`, Next steps):
the v5 replay (`97648603`) showed the opponent running `COW`/`MILK` and
`SHEEP`/`WOOL` plus direct `FERTILIZER` sales, income streams we have
none of.

Starting with **goose/egg** rather than cow or sheep (see chat design
discussion): cheapest to buy ($300 vs $400/$500), fastest first yield
(day 4 vs day 8/6), and simplest production cadence -- eggs are produced
every day once fed, so there's no "every N days" interval bookkeeping to
get right before the rest of the mechanism (`FEED`/`HARVEST`/`CARE`/
`COLLECT_FERTILIZER`) is validated. `COOP` and `PASTURE` are structurally
the same kind of thing, so this should generalize to cow/sheep afterward
by parametrizing the structure type and the production interval.

Plan, in increments (each validated before moving to the next):
1. **Mini-test**: confirm the real shape of a `COOP` tile and a placed
   animal's fields on an actual `obs`, not just from `README.md`.
2. **Get a live goose on the coop**: `BUY_ANIMAL` -> `PICKUP` ->
   `BUILD_COOP` -> `PLACE`, nothing else yet (no `FEED`/`HARVEST`).
3. Layer in `FEED`, `HARVEST`, `CARE`, `COLLECT_FERTILIZER`, and selling
   `EGG`/`FERTILIZER`.
4. Generalize to `COW`/`SHEEP` (pasture, interval-based production).


In [15]:
import sys
from pathlib import Path

from kaggle_environments import make

sys.path.insert(0, str(Path.cwd().parent / "src"))

from kaggriculture_bot.evaluate import evaluate
from kaggriculture_bot.strategies.baseline import melon_then_wheat_extra_hands_agent


## Mini-test: confirm `COOP` / animal tile shape on a real `obs`

Same pattern as notebook 11's `_test_buy_land_agent`: a throwaway agent
that just does `BUILD_COOP` (and later `BUY_ANIMAL`/`PICKUP`/`PLACE`) and
otherwise passes, run directly against `test_env`, then inspect the
resulting tile dict and shed/inventory fields on the real `obs` -- don't
assume the README's documented shape matches without checking.

This ended up growing past a one-shot shape check into the full
lifecycle agent below (`_test_goose_agent`), debugged iteratively against
the real `obs` rather than written in one pass -- see "Validate" for what
was actually confirmed and the bugs found along the way.


In [16]:
def _test_goose_agent(obs):
    market = []
    market.append(["BUY_PRODUCT", "WHEAT", 1])
    if obs["step"] == 0:
        market.append(["BUY_ANIMAL", "GOOSE", 1])
        
    farmer = []
    farmer_pos = obs["farms"][obs["player"]]["farmer"]
    x, y = farmer_pos
    tile = obs["farms"][obs["player"]]["tiles"][y][x]

    if tile is None:
        farmer = ["BUILD_COOP"]
    elif tile is not None and tile.get("kind") == "COOP" and obs["private"]["inventories"][0].get("GOOSE", 0) == 0 and tile.get("animal") != "GOOSE":
        farmer = ["PICKUP", "GOOSE", 1]
    elif tile is not None and tile.get("kind") == "COOP" and obs["private"]["inventories"][0].get("GOOSE", 0) > 0 and tile.get("animal") != "GOOSE":
            farmer = ["PLACE", "GOOSE", 1]
    if tile is not None and tile.get("kind") == "COOP" and tile.get("animal") == "GOOSE":
        if obs["private"]["inventories"][0].get("WHEAT", 0) == 0:
            farmer = ["PICKUP", "WHEAT", 1]
        elif not tile.get("fed_today"):
            farmer = ["FEED"]
        elif tile.get("fertilizer_available"):
            farmer = ["COLLECT_FERTILIZER"]
        elif not tile.get("cared_today"):
            farmer = ["CARE"]
        else:
            farmer = ["PASS"]
             
    return {"farmer": farmer, "hands": [], "market": market}


test_env = make("kaggriculture", configuration={"episodeSteps": 720}, debug=True)
test_env.run([_test_goose_agent, "random"])

[[{'action': {'farmer': ['PASS'], 'hands': [], 'market': []},
   'reward': 0,
   'info': {},
   'observation': {'remainingOverageTime': 60,
    'step': 0,
    'player': 0,
    'farms': [{'money': 3000.0,
      'tiles': [[None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED'],
       [None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED'],
       [None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED'],
       [None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED'],
       [None,
        None,
        None,
        None,
        None,
        'LOCKED',
        'LOCKED',
        'LOCKED',
        'LOCKED',
 

In [17]:
prev = None
for i, step in enumerate(test_env.steps):
    obs = step[0]["observation"]
    action = step[0]["action"]["farmer"]
    farm = obs["farms"][obs["player"]]
    x, y = farm["farmer"]
    tile = farm["tiles"][y][x]
    shed_goose = obs["private"]["shed"].get("GOOSE", 0)
    inv_goose = obs["private"]["inventories"][0].get("GOOSE", 0)
    snapshot = (tile, shed_goose, inv_goose)
    if snapshot != prev:
        print(i, "tile:", tile, "| shed GOOSE:", shed_goose, "| farmer inv GOOSE:", inv_goose ,"| action:", action)
        prev = snapshot


0 tile: None | shed GOOSE: 0 | farmer inv GOOSE: 0 | action: ['PASS']
1 tile: {'kind': 'COOP'} | shed GOOSE: 1 | farmer inv GOOSE: 0 | action: ['BUILD_COOP']
2 tile: {'kind': 'COOP'} | shed GOOSE: 0 | farmer inv GOOSE: 1 | action: ['PICKUP', 'GOOSE', 1]
3 tile: {'kind': 'COOP', 'animal': 'GOOSE', 'placed_day': 0, 'yield_units': 0, 'consecutive_unfed': 0, 'fed_today': False, 'cared_today': False, 'fertilizer_available': False, 'pending_care_bonus': 0} | shed GOOSE: 0 | farmer inv GOOSE: 0 | action: ['PLACE', 'GOOSE', 1]
5 tile: {'kind': 'COOP', 'animal': 'GOOSE', 'placed_day': 0, 'yield_units': 0, 'consecutive_unfed': 0, 'fed_today': True, 'cared_today': False, 'fertilizer_available': False, 'pending_care_bonus': 0} | shed GOOSE: 0 | farmer inv GOOSE: 0 | action: ['FEED']
7 tile: {'kind': 'COOP', 'animal': 'GOOSE', 'placed_day': 0, 'yield_units': 0, 'consecutive_unfed': 0, 'fed_today': True, 'cared_today': True, 'fertilizer_available': False, 'pending_care_bonus': 0} | shed GOOSE: 0 | f

## Validate

Validated directly against `obs` over a full 720-step run (trace loop
above `_test_goose_agent`, extended to also print the action taken each
turn): the goose survives the entire game (`consecutive_unfed` never
exceeds 0), and every day settles into the same clean cycle once nothing
is left to do -- `PASS` (new day) -> `FEED` -> `COLLECT_FERTILIZER` ->
`CARE` -> `PASS` for the rest of the day.

Bugs found and fixed along the way, in order:
- `tile.get(...)` called unconditionally on a `tile` that can be `None`
  (step 0, before `BUILD_COOP`) -- needs an explicit `tile is not None`
  guard.
- A freshly-built empty `COOP` (`{'kind': 'COOP'}`, no animal placed yet)
  has no `placed_day` key -- that key (and `coop_age`) only exists once
  `tile.get("animal") == "GOOSE"`.
- `FEED` consumes `WHEAT` from the farmer's *inventory*, not the shed --
  same `PICKUP`-before-use pattern as `GOOSE` after `BUY_ANIMAL`. Bought
  via `BUY_PRODUCT` every turn as a test-only shortcut (money isn't a
  constraint here), not `BUY_SEED`, which would require growing it.
- `coop_age >= 1` is not the same condition as "not fed today" -- it's
  true every day from day 1 onward, so it permanently starved out the
  `COLLECT_FERTILIZER`/`CARE` `elif` branches below it. Fixed by keying
  off `tile.get("fed_today")` directly.
- `fertilizer_available` lives on the `tile`, not on
  `obs["private"]["shed"]`.
- The setup branches (`PICKUP GOOSE` / `PLACE GOOSE`) stayed permanently
  true even after the goose was already placed and alive (nothing in
  their condition ever turned off), silently winning `farmer` every turn
  the daily-care block had nothing left to do that day. Fixed by adding
  `tile.get("animal") != "GOOSE"`, so they only fire during setup.
- No explicit fallback once everything is done for the day -- `farmer`
  must default to `["PASS"]`, not `[]`.

`pending_care_bonus` banks correctly (+1/day while both fed and cared)
and pays out on the first scheduled production (day 4: base 1 + 3
banked = 4, landing exactly on `max_held`), matching the README's
description of animal care.

Out of scope for this increment: `HARVEST`/`SELL` -- eggs accumulate to
the `max_held` cap and are never collected or sold, so no income from
this yet. `melon_then_wheat_extra_hands_agent` already has a hand that
grows and sells wheat, which resolves the `BUY_PRODUCT` shortcut used
here -- next step is folding this goose logic into a new hand there
(using that hand's own wheat) rather than continuing in isolation.


## Integrating into `melon_then_wheat_extra_hands_agent`

`_test_goose_agent` above validates the mechanism in isolation. Folding
it into the current best agent as a dedicated hand, decisions made so
far (see chat):

- **Dedicated hand, not shared** -- a new hand (index 8) whose only job
  is the goose, rather than timesharing an existing crop-tending hand.
- **Hired after NE, cap raised to 9** -- same pattern as hands 5/6/7
  (`ne_zone_by_index`, hire-cap `elif` chain), not from day 0.
- **Coop at `(8, 3)`** -- the one NE tile no existing zone claims (see
  `ZONE_RIGHT_NE`'s comment: "15 tiles minus (8,3) = 14").
- **Reserve wheat before selling it** -- the farmer currently does
  `SELL WHEAT wheat_in_shed` (the *entire* shed) every turn it's
  positive; the goose hand's `PICKUP WHEAT` needs something left to
  find there.
- **`HARVEST`/`SELL EGG`** -- validate the egg's `HARVEST` destination
  (shed vs. inventory) the same way `FEED`'s wheat source was confirmed
  above, before wiring the sell.

Starting point below is an exact copy of `melon_then_wheat_extra_hands_agent`
(unmodified) to edit in place, one decision at a time, same as
`_test_goose_agent` was built above -- rather than editing
`baseline.py` directly, per this project's notebook-first validation
practice.


In [ ]:
from kaggriculture_bot.strategies.baseline import (
    DIRECTIONS,
    HAND_ZONES,
    LOOP_ORDER_12,
    LOOP_ORDER_HANDS,
    LOOP_ORDER_HANDS_NE,
    SPAWN_FEEDER,
    SPAWN_FEEDER_NE,
    ZONE_LEFT_NE,
    ZONE_RIGHT_NE,
    ZONE_TOP_NE,
)

# Zone for the goose hand (index 8): (8,3) is the one NE tile no
# existing zone claims (see ZONE_RIGHT_NE's comment: "15 tiles minus
# (8,3) = 14"), but it isn't on LOOP_ORDER_HANDS_NE's border loop, so a
# bare self-loop {(8,3): (8,3)} is unreachable -- nothing ever routes a
# hand onto it. Needs an entry from the border, same mechanism as
# ZONE_TOP_NE/ZONE_LEFT_NE/ZONE_RIGHT_NE overriding an existing border
# key: (9,3) is on the border and orthogonally adjacent to (8,3), so
# redirect that one key off the border into (8,3), then self-loop there.
GOOSE_ZONE_NE = {(9, 3): (8, 3), (8, 3): (8, 3)}

# The 4 tiles adjacent to the shed -- PICKUP/DROP only work standing on
# one of these (AGENTS.md). (8,3) is never one of them, and hands
# respawn here at the start of every day (confirmed via trace: hand 8
# reappears at (4,4) every ~24 steps), so WHEAT/GOOSE have to be picked
# up while passing through here on the way to (8,3), not once arrived.
SHED_ADJACENT = {(4, 4), (5, 4), (4, 5), (5, 5)}


# melon_then_wheat_extra_hands_agent (baseline.py) extended with a 9th
# hand (index 8) dedicated to a goose/egg on GOOSE_ZONE_NE, hired only
# once NE is bought (hire cap raised 8 -> 9, same elif chain as
# hands 5/6/7). Decisions from chat, see the markdown above.
def _test_goose_integration_agent(obs):
    crop_to_plant = "MELON" if obs["day"] < 10 else "WHEAT"
    crop_seeds = obs["private"]["seeds"].get(crop_to_plant, 0)

    market = []
    hands = []

    ne_zone_by_index = {5: ZONE_TOP_NE, 6: ZONE_LEFT_NE, 7: ZONE_RIGHT_NE, 8: GOOSE_ZONE_NE}

    for i, (hx, hy) in enumerate(obs["farms"][obs["player"]]["hands"]):
        if i in ne_zone_by_index:
            own_zone = ne_zone_by_index[i]
            hand_loop = {**LOOP_ORDER_HANDS_NE, **SPAWN_FEEDER_NE, **own_zone}
        else:
            own_zone = HAND_ZONES[i % len(HAND_ZONES)]
            hand_loop = {**LOOP_ORDER_HANDS, **SPAWN_FEEDER, **own_zone}

        target_x, target_y = hand_loop[(hx, hy)]
        if (target_x, target_y) == (hx, hy):
            move = ["PASS"]
        else:
            move = [DIRECTIONS[(target_x - hx, target_y - hy)]]

        hand_tile = obs["farms"][obs["player"]]["tiles"][hy][hx]
        in_own_zone = (hx, hy) in own_zone

        if own_zone == GOOSE_ZONE_NE:
            hand_inventory = obs["private"]["inventories"][i + 1]

            if (hx, hy) != (8, 3):
                # Not at the coop yet. PICKUP only works shed-adjacent,
                # which (8,3) never is -- grab what's needed for the day
                # while passing through the shed corners on the way in,
                # instead of walking there empty-handed.
                if (hx, hy) in SHED_ADJACENT and hand_inventory.get("GOOSE", 0) == 0 and obs["private"]["shed"].get("GOOSE", 0) > 0:
                    op = ["PICKUP", "GOOSE", 1]
                elif (hx, hy) in SHED_ADJACENT and hand_inventory.get("WHEAT", 0) == 0:
                    op = ["PICKUP", "WHEAT", 1]
                else:
                    op = move
            else:
                if hand_tile is None:
                    op = ["BUILD_COOP"]
                elif hand_tile.get("kind") == "COOP" and hand_tile.get("animal") != "GOOSE":
                    if hand_inventory.get("GOOSE", 0) > 0:
                        op = ["PLACE", "GOOSE", 1]
                    elif obs["private"]["shed"].get("GOOSE", 0) == 0:
                        # Not carrying one and none waiting in the shed
                        # either -- buy it now so it's there to pick up
                        # on tomorrow's walk in (can't PICKUP here).
                        market.append(["BUY_ANIMAL", "GOOSE", 1])
                        op = ["PASS"]
                    else:
                        op = ["PASS"]
                else:
                    if hand_inventory.get("WHEAT", 0) == 0:
                        # Missed the wheat pickup on the way in -- can't
                        # PICKUP from here either; skip feeding today
                        # and catch it on tomorrow's walk instead.
                        op = ["PASS"]
                    elif not hand_tile.get("fed_today"):
                        op = ["FEED"]
                    elif hand_tile.get("fertilizer_available"):
                        op = ["COLLECT_FERTILIZER"]
                    elif not hand_tile.get("cared_today"):
                        op = ["CARE"]
                    elif hand_tile.get("yield_units", 0) > 0:
                        op = ["HARVEST"]
                    else:
                        op = ["PASS"]
                        egg_in_shed = obs["private"]["shed"].get("EGG", 0)
                        if egg_in_shed > 0:
                            market.append(["SELL", "EGG", egg_in_shed])
        elif hand_tile == "LOCKED" or not in_own_zone:
            op = move
        elif hand_tile is None and crop_seeds > 0:
            op = ["PLANT", crop_to_plant]
        elif hand_tile is not None and hand_tile.get("kind") == "PLANT":
            crop_age = obs["day"] - hand_tile["planted_day"]
            threshold = 10 if hand_tile["crop"] == "MELON" else 2
            if crop_age >= threshold:
                op = ["HARVEST"]
            elif not hand_tile.get("watered_today"):
                op = ["WATER"]
            else:
                op = move
        else:
            op = move
        hands.append(op)

    if len(obs["farms"][obs["player"]]["hands"]) < 5:
        market.append(["HIRE"])
    elif (
        len(obs["farms"][obs["player"]]["unlocked_quadrants"]) > 1
        and len(obs["farms"][obs["player"]]["hands"]) < 9
    ):
        market.append(["HIRE"])

    if obs["step"] == 0 or crop_seeds <= 5:
        market.append(["BUY_SEED", crop_to_plant, 9 - crop_seeds])

    if (
        obs["farms"][obs["player"]]["money"] >= 1000
        and len(obs["farms"][obs["player"]]["unlocked_quadrants"]) == 1
        and crop_to_plant == "WHEAT"
    ):
        market.append(["BUY_LAND"])

    farmer_pos = obs["farms"][obs["player"]]["farmer"]
    x, y = farmer_pos
    target_x, target_y = LOOP_ORDER_12[(x, y)]
    direction = DIRECTIONS[(target_x - x, target_y - y)]

    tile = obs["farms"][obs["player"]]["tiles"][y][x]

    wheat_in_shed = obs["private"]["shed"].get("WHEAT", 0)
    melon_in_shed = obs["private"]["shed"].get("MELON", 0)
    # Reserve 1 WHEAT (FEED's daily consumption) before selling the
    # rest, so the goose hand's PICKUP WHEAT has something to find.
    if wheat_in_shed > 1:
        market.append(["SELL", "WHEAT", wheat_in_shed - 1])
    if melon_in_shed > 0:
        market.append(["SELL", "MELON", melon_in_shed])

    if tile is None and crop_seeds > 0:
        farmer = ["PLANT", crop_to_plant]
    elif tile is not None and tile.get("kind") == "PLANT":
        crop_age = obs["day"] - tile["planted_day"]
        threshold = 10 if tile["crop"] == "MELON" else 2
        if crop_age >= threshold:
            farmer = ["HARVEST"]
        elif not tile.get("watered_today"):
            farmer = ["WATER"]
        else:
            farmer = [direction]
    else:
        farmer = [direction]

    return {"farmer": farmer, "hands": hands, "market": market}


## Validate the integration

Same approach as the mini-test above: run `test_env` directly and trace
the real `obs`, this time centered on hand 8 (position, its tile,
`inventories[9]`) instead of the farmer -- against
`melon_then_wheat_extra_hands_agent` itself as the opponent, since that's
the baseline this increment needs to beat. Watching for: hand 8 hired
only after NE, the setup sequence completing at `(8, 3)`, then the same
daily cycle validated above, now with `HARVEST`/`SELL EGG` included.


In [ ]:
test_env_integration = make("kaggriculture", configuration={"episodeSteps": 720}, debug=True)
test_env_integration.run([_test_goose_integration_agent, melon_then_wheat_extra_hands_agent])

prev = None
saw_hand_8 = False
for i, step in enumerate(test_env_integration.steps):
    obs = step[0]["observation"]
    farm = obs["farms"][obs["player"]]
    hands_pos = farm["hands"]
    n_hands = len(hands_pos)
    if n_hands < 9:
        continue
    saw_hand_8 = True

    hx, hy = hands_pos[8]
    goose_tile = farm["tiles"][hy][hx]
    hand8_inv = obs["private"]["inventories"][9]
    shed_goose = obs["private"]["shed"].get("GOOSE", 0)
    money = farm["money"]
    hand8_action = step[0]["action"]["hands"][8] if len(step[0]["action"]["hands"]) > 8 else None

    snapshot = (n_hands, (hx, hy), goose_tile, hand8_inv.get("GOOSE", 0), hand8_inv.get("WHEAT", 0), shed_goose, money)
    if snapshot != prev:
        print(
            i,
            "hands:", n_hands,
            "| hand8 pos:", (hx, hy),
            "| tile:", goose_tile,
            "| hand8 inv GOOSE/WHEAT:", hand8_inv.get("GOOSE", 0), hand8_inv.get("WHEAT", 0),
            "| shed GOOSE:", shed_goose,
            "| money:", money,
            "| hand8 action:", hand8_action,
        )
        prev = snapshot

if not saw_hand_8:
    print("Hand 8 was never hired in this run (NE never bought, or ran out of turns) -- nothing to trace.")


## Evaluate against `melon_then_wheat_extra_hands_agent`

The trace above confirms the mechanism works end-to-end inside the full
agent (setup completes, daily `FEED` cycle holds). The real question is
whether the goose hand's income (plus its hiring cost and the reserved
wheat no longer sold) actually beats the current best agent, not just
whether it runs without erroring.


In [ ]:
evaluate(_test_goose_integration_agent, melon_then_wheat_extra_hands_agent, n=10)


**Result: `{'win_rate': 0.0, 'avg_money': 20004.0}` (10 episodes).** The
goose hand, as built, loses every game to the baseline it's supposed to
beat -- a negative result, not a bug (the mechanism itself is validated
and working, per the trace above). This harness only returns agent0's
own `win_rate`/`avg_money`, not the opponent's, so it's not yet clear
whether this is close or a blowout.

Hypotheses for the next session, roughly in order of likely impact --
none tested yet:
- **Overhead vs. payout.** Eggs cap at `max_held=4` and sell at a base
  price of `50` (`obs["market"]["inventory"]`, confirmed in the mini-test
  trace) -- a low ceiling on income from one animal. The hire cost itself
  is cheap (`fib(n)`, $1 if hired alone that day), so the more likely
  drag is the daily NE-border walk (~8+ of the day's 24 turns, every day,
  confirmed in the integration trace) -- time that produces nothing,
  though it's not stolen from an existing crop-tending hand since this
  is a net-new hire.
- **Wheat reservation cost.** `if wheat_in_shed > 1: sell wheat_in_shed - 1`
  permanently forgoes selling 1 unit of wheat for the rest of the game
  once the shed has a surplus -- probably small next to a $20k bankroll,
  but not measured in isolation.
- **Placement delay.** In the traced game the goose wasn't placed until
  `placed_day: 14` (NE has to be bought, the hand hired, and it has to
  make it through a couple of shed round-trips first) -- more than half
  the 30-day season is gone before any income starts, on top of the
  `max_held` ceiling.

Before trying fixes: worth first checking whether `_test_goose_integration_agent`
still beats `melon_then_wheat_extra_hands_agent` in *pure days-with-a-goose*
terms (i.e. isolate whether the egg income alone, ignoring the wheat
reservation and hire, is even positive) -- otherwise any fix targets the
wrong cost.
